In [2]:
import geopandas as gpd
import pandas as pd

In [3]:
rental_data_sf = pd.read_csv("../data/curated/rental_data_sf.csv")

In [4]:
rental_data_sf.head(2)

,name,cost_text,coordinates,property type,beds,baths,parking,title,description,property features,NBN,Weekly Rent Amount,Postcode,geometry,SA2_CODE21,SA2_NAME21
0,5401/308 Exhibition Street Melbourne VIC 3000,"$3,750 weekly","[-37.8085173, 144.9696285]",Apartment / Unit / Flat,3 Beds,2 Baths,4 Parking,"BRAND NEW AT THE SAPHIRE - 3 BDR. 2.5 BTH, 4 ...",['Designed by Cox Architects and Fender Katsal...,['Built in wardrobes*'],No NBN,3750.0,3000.0,POINT (144.9696285 -37.8085173),206041503.0,Melbourne CBD - East
1,4904/63 Latrobe St Melbourne VIC 3000,"$2,900/week","[-37.8082025, 144.9693999]",Apartment / Unit / Flat,3 Beds,3 Baths,2 Parking,Brand New luxurious 3 bedroom residence | Home...,['Welcome to your exclusive opportunity to res...,"['INSIDE:', 'Gym', 'Intercom', 'Floorboards', ...",No NBN,2900.0,3000.0,POINT (144.9693999 -37.8082025),206041503.0,Melbourne CBD - East


In [14]:
print(list(rental_data_sf.dtypes))

[dtype('O'), dtype('O'), dtype('O'), dtype('O'), dtype('O'), dtype('O'), dtype('O'), dtype('O'), dtype('O'), dtype('O'), dtype('O'), dtype('float64'), dtype('float64'), dtype('O'), dtype('float64'), dtype('O')]


In [40]:
postcode_counts = rental_data_sf.groupby(['Postcode']).agg({'name': 'count'})
postcode_counts_sorted = postcode_counts.sort_values(by='name', ascending=False)
suburbs_less_5_properties = postcode_counts_sorted[postcode_counts_sorted['name'] == 1]
suburbs_less_5_properties
postcode_counts_sorted.index = postcode_counts_sorted.index.astype(int)
postcode_count = postcode_counts_sorted.reset_index()

,Postcode,name
0,3000,818
1,3006,320
2,3141,183
3,3350,182
4,3029,175
...,...,...
423,3733,1
424,3732,1
425,3720,1
426,3700,1


In [11]:
suburb_info = gpd.read_file("../data/landing/1270055003_poa_2016_aust_shape/POA_2021_AUST_GDA2020.shp")

In [12]:
suburb_info.head(2)

,POA_CODE21,POA_NAME21,AUS_CODE21,AUS_NAME21,AREASQKM21,LOCI_URI21,SHAPE_Leng,SHAPE_Area,geometry
0,0800,0800,AUS,Australia,3.1731,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.081893,0.000264,"POLYGON ((130.83681 -12.45376, 130.83684 -12.4..."
1,0810,0810,AUS,Australia,24.4283,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.241859,0.002031,"POLYGON ((130.89986 -12.36567, 130.89875 -12.3..."


In [49]:
vic_suburbs = suburb_info[suburb_info["POA_CODE21"].astype(str).str.startswith('3')]
vic_suburbs.head(2)

,POA_CODE21,POA_NAME21,AUS_CODE21,AUS_NAME21,AREASQKM21,LOCI_URI21,SHAPE_Leng,SHAPE_Area,geometry
672,3000,3000,AUS,Australia,2.4814,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.083491,0.000254,"POLYGON ((144.96139 -37.82050, 144.96063 -37.8..."
673,3002,3002,AUS,Australia,1.8557,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.059488,0.000190,"POLYGON ((144.98978 -37.81906, 144.98973 -37.8..."


In [44]:
geoJSON = vic_suburbs[['POA_CODE21', 'geometry']].drop_duplicates('POA_CODE21').to_json()

In [25]:
import folium

In [36]:
print(type(postcode_count),type(geoJSON))

<class 'pandas.core.frame.DataFrame'> <class 'str'>


In [65]:
vic_suburbs['POA_NAME21'] = vic_suburbs['POA_NAME21'].values.astype(int)

In [60]:
postcode_count['Postcode'].values

array([3000, 3006, 3141, 3350, 3029, 3030, 3008, 3053, 3064, 3550, 3182,
       3121, 3011, 3181, 3338, 3216, 3199, 3978, 3024, 3977, 3128, 3217,
       3003, 3051, 3004, 3046, 3122, 3056, 3073, 3163, 3168, 3032, 3150,
       3183, 3145, 3012, 3040, 3205, 3175, 3500, 3840, 3184, 3220, 3810,
       3031, 3044, 3204, 3072, 3058, 3101, 3690, 3207, 3067, 3021, 3124,
       3335, 3215, 3161, 3023, 3166, 3055, 3195, 3219, 3108, 3146, 3066,
       3057, 3186, 3125, 3223, 3336, 3806, 3068, 3226, 3083, 3165, 3941,
       3218, 3429, 3844, 3174, 3071, 3136, 3123, 3936, 3070, 3152, 3337,
       3039, 3809, 3142, 3630, 3149, 3079, 3228, 3214, 3754, 3041, 3084,
       3076, 3109, 3358, 3185, 3134, 3280, 3020, 3037, 3015, 3931, 3104,
       3162, 3939, 3042, 3103, 3169, 3196, 3054, 3305, 3002, 3065, 3151,
       3750, 3756, 3753, 3013, 3187, 3356, 3028, 3192, 3043, 3340, 3052,
       3082, 3820, 3805, 3155, 3995, 3825, 3198, 3143, 3188, 3555, 3047,
       3922, 3156, 3875, 3153, 3194, 3148, 3193, 31

In [98]:
postcode_count1 = postcode_count[postcode_count['name'] > 3]
postcode_count1

,Postcode,name
0,3000,818
1,3006,320
2,3141,183
3,3350,182
4,3029,175
...,...,...
297,3284,4
298,3380,4
299,3938,4
300,3944,4


In [99]:
import numpy as np
# Merge the GeoDataFrame with your count dataframe based on a common postcode key

merged_data = vic_suburbs.merge(postcode_count1, left_on='POA_NAME21', right_on='Postcode', how='left')
merged_data['name'] = np.log(merged_data.name.values)

In [100]:
merged_data.head(2)

,POA_CODE21,POA_NAME21,AUS_CODE21,AUS_NAME21,AREASQKM21,LOCI_URI21,SHAPE_Leng,SHAPE_Area,geometry,Postcode,name
0,3000,3000,AUS,Australia,2.4814,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.083491,0.000254,"POLYGON ((144.96139 -37.82050, 144.96063 -37.8...",3000.0,6.706862
1,3002,3002,AUS,Australia,1.8557,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.059488,0.000190,"POLYGON ((144.98978 -37.81906, 144.98973 -37.8...",3002.0,3.496508


In [101]:


# Create the folium map
_map = folium.Map(location=[-37.020100, 144.964600], tiles="Stamen Terrain", zoom_start=10)

# Add the choropleth layer with color based on count
_map.add_child(folium.Choropleth(
    geo_data=merged_data,
    name='choropleth',
    data=merged_data,
    columns=['POA_NAME21', 'name'],  # Use the appropriate column names from your count dataframe
    key_on='feature.properties.POA_NAME21',
    fill_color='YlGnBu',
    fill_opacity=0.7,
    line_opacity=0.2,
    legend_name='Log Count Legend'
))

_map

# Add a color scale legend
#colormap.add_to(_map)


In [41]:
# Create a colormap for coloring the postcodes based on their count
#colormap = folium.LinearColormap(colors=['green', 'yellow', 'red'], vmin=merged_data['count'].min(), vmax=merged_data['count'].max())

# Create the folium map
_map = folium.Map(location=[-37.020100, 144.964600], tiles="Stamen Terrain", zoom_start=10)

# Add the choropleth layer with color based on count
_map.add_child(folium.Choropleth(
    geo_data=geoJSON['geometry'],
    name='choropleth',
    data=postcode_count,
    columns=['POA_CODE21', 'Postcode'],
    #key_on='feature.properties.postcode_column_in_geoJSON',
    fill_color='YlGn',
    fill_opacity=0.7,
    line_opacity=0.2,
    legend_name='Count Legend'
))

_map


KeyError: "None of ['POA_CODE21'] are in the columns"

In [9]:
_map = folium.Map(location=[-37.020100, 144.964600], tiles="Stamen Terrain", zoom_start=10)

# refer to the folium documentations on how to plot aggregated data.
_map.add_child(folium.Choropleth(
    geo_data=geoJSON,
    name='choropleth',
))

_map